In [ ]:
import time
import numpy as np
import pandas as pd
import os
import cocoex
from mealpy.swarm_based.SFO import OriginalSFO
from mealpy import FloatVar
import re

# 1. Inicjalizacja zestawu funkcji BBOB z platformy COCO
suite_name = "bbob"
dimensions = [2, 3, 10]
suite = cocoex.Suite(suite_name, "", f"dimensions: {','.join(map(str, dimensions))}")
suite_options = "dimensions: 2,3,10"
suite = cocoex.Suite(suite_name, "", suite_options)

seeds = list(range(12345, 12395)) 

max_fe_config = {
    2: 20000,
    3: 30000,
    10: 100000
}

output_filename = "OriginalSFO_wyniki.xlsx"

print("Rozpoczynanie bezpiecznego eksperymentu z limitem max_fe dla OriginalSFO...")

for problem in suite:
    dim = problem.dimension
    func_name = problem.name

    if dim not in dimensions:
        continue
        
    max_fe = max_fe_config[dim]

    match_f = re.search(r'f\d+', problem.name)
    func_short = match_f.group(0) if match_f else "fX"
    
    sheet_name = f"{func_short}_{dim}D"
    
    # Sprawdzamy, czy dany arkusz jest już w pliku
    if os.path.exists(output_filename):
        try:
            excel_file = pd.ExcelFile(output_filename)
            if sheet_name in excel_file.sheet_names:
                print(f"Pominięto (już zapisane w pliku): {sheet_name}")
                continue
        except Exception:
            pass

    print(f"Testowanie: {func_name} | Wymiar: {dim}D (Limit FE: {max_fe})")
    
    results_list = []
    lb = problem.lower_bounds
    ub = problem.upper_bounds
    
    problem_dict = {
        "obj_func": problem,
        "bounds": FloatVar(lb=lb, ub=ub),
        "minmax": "min"
    }
    
    for idx, seed in enumerate(seeds):
        start_time = time.time()
        
        try:
            model = OriginalSFO(epoch=100000, pop_size=30)
            termination_condition = {"max_fe": max_fe}
            
            # Bezpieczne uruchomienie (przypisujemy wynik do pojedynczej zmiennej)
            best_agent = model.solve(
                problem_dict, 
                seed=seed, 
                termination=termination_condition
            )
            
            # Uniwersalne wyciągnięcie wartości fitness niezależnie od wersji Mealpy
            if hasattr(best_agent, "target") and hasattr(best_agent.target, "fitness"):
                best_fitness = best_agent.target.fitness
            elif isinstance(best_agent, (tuple, list)) and len(best_agent) >= 2:
                best_fitness = best_agent[1]
            elif hasattr(model, 'g_best') and model.g_best is not None:
                best_fitness = model.g_best.target.fitness
            elif hasattr(model, 'solution') and model.solution is not None:
                best_fitness = model.solution.target.fitness
            else:
                best_fitness = float(best_agent)
                
            # Jeśli fitness jest tablicą/listą (np. z jedną wartością), wyciągnij skalar
            if isinstance(best_fitness, (np.ndarray, list)):
                best_fitness = float(best_fitness[0])
            
            if hasattr(model, 'n_fe'):
                fe_used = model.n_fe
            elif hasattr(model.history, 'n_fe'):
                fe_used = model.history.n_fe
            else:
                fe_used = max_fe
                
        except Exception as e:
            print(f"--> Błąd w funkcji {func_name} przy ziarnie {seed}: {e}")
            best_fitness = float('nan')
            fe_used = 0
            
        elapsed_time = time.time() - start_time
        
        results_list.append({
            "Run": idx + 1,
            "Seed": seed,
            "Best_Fitness": best_fitness,
            "Time_s": elapsed_time,
            "FE_Used": fe_used
        })
        
    df_res = pd.DataFrame(results_list)
    
    # Statystyki (pomijają NaN)
    mean_fit = df_res["Best_Fitness"].mean()
    std_fit = df_res["Best_Fitness"].std()
    mean_time = df_res["Time_s"].mean()
    std_time = df_res["Time_s"].std()
    
    summary_row = pd.DataFrame([{
        "Run": "STAT", "Seed": "-", 
        "Best_Fitness": f"Średnia: {mean_fit:.4e} ± {std_fit:.4e}",
        "Time_s": f"Średnia: {mean_time:.2f}s ± {std_time:.2f}s",
        "FE_Used": "-"
    }])
    
    df_final = pd.concat([df_res, summary_row], ignore_index=True)
    
    # Natychmiastowy zapis
    if not os.path.exists(output_filename):
        df_final.to_excel(output_filename, sheet_name=sheet_name, index=False)
    else:
        with pd.ExcelWriter(output_filename, engine="openpyxl", mode="a", if_sheet_exists="replace") as writer:
            df_final.to_excel(writer, sheet_name=sheet_name, index=False)
            
    print(f"--> Zapisano arkusz: {sheet_name}")

print("Wszystkie eksperymenty zakończone pomyślnie!")

2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: OriginalSFO(epoch=100000, pop_size=30, pp=0.1, AP=4.0, epsilon=0.0001)
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 1, Current best: 79.48586189128692, Global best: 79.48586189128692, Runtime: 0.01635 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 2, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01376 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 3, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01533 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 4, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01184 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 5, Current best: 79.48004052155329, Global best: 79

Rozpoczynanie bezpiecznego eksperymentu z limitem max_fe dla OriginalSFO...
Testowanie: BBOB suite problem f1 instance 1 in 2D | Wymiar: 2D (Limit FE: 20000)


2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 11, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01054 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 12, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01344 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 13, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.02119 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 14, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01424 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 15, Current best: 79.48004052155329, Global best: 79.48004052155329, Runtime: 0.01448 seconds
2026/10/26 09:50:35 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 16

--> Zapisano arkusz: f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Pominięto (już zapisane w pliku): f1_2D
Testowanie: BBOB suite problem f2 instance 1 in 2D | Wymiar: 2D (Limit FE: 20000)


2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 6, Current best: -208.97243096096653, Global best: -208.97243096096653, Runtime: 0.01459 seconds
2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 7, Current best: -208.97243096096653, Global best: -208.97243096096653, Runtime: 0.03381 seconds
2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 8, Current best: -208.97243096096653, Global best: -208.97243096096653, Runtime: 0.01282 seconds
2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 9, Current best: -208.97243096096653, Global best: -208.97243096096653, Runtime: 0.01100 seconds
2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 10, Current best: -208.97243096096653, Global best: -208.97243096096653, Runtime: 0.01198 seconds
2026/10/26 09:51:26 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Probl

...

2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 12, Current best: 510.04273353947497, Global best: 510.04273353947497, Runtime: 0.01479 seconds
2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 13, Current best: 510.04273353947497, Global best: 510.04273353947497, Runtime: 0.01578 seconds
2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 14, Current best: 510.04273353947497, Global best: 510.04273353947497, Runtime: 0.01203 seconds
2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 15, Current best: 510.04273353947497, Global best: 510.04273353947497, Runtime: 0.01140 seconds
2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 16, Current best: 510.04273353947497, Global best: 510.04273353947497, Runtime: 0.01476 seconds
2026/10/26 11:06:24 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P,

--> Zapisano arkusz: f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D


2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: OriginalSFO(epoch=100000, pop_size=30, pp=0.1, AP=4.0, epsilon=0.0001)


Pominięto (już zapisane w pliku): f8_10D
Pominięto (już zapisane w pliku): f8_10D
Testowanie: BBOB suite problem f9 instance 1 in 10D | Wymiar: 10D (Limit FE: 100000)


2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 1, Current best: 181.87486449562053, Global best: 181.87486449562053, Runtime: 0.02318 seconds
2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 2, Current best: 175.19248709811365, Global best: 175.19248709811365, Runtime: 0.01843 seconds
2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 3, Current best: 175.19248709811365, Global best: 175.19248709811365, Runtime: 0.01762 seconds
2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 4, Current best: 175.19248709811365, Global best: 175.19248709811365, Runtime: 0.01855 seconds
2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoch: 5, Current best: 175.19248709811365, Global best: 175.19248709811365, Runtime: 0.01669 seconds
2026/10/26 11:10:38 PM, INFO, mealpy.swarm_based.SFO.OriginalSFO: >>>Problem: P, Epoc